<a href="https://colab.research.google.com/github/Stupid-PHM-boy/Physics-informed-machine-learning-based-on-TCN/blob/main/%E2%80%9CSimply_cases_2_ipynb%E2%80%9D%E7%9A%84%E5%89%AF%E6%9C%AC.ipynb" target="_parent"><img src="https://colab.research.google.com/assets/colab-badge.svg" alt="Open In Colab"/></a>

In [6]:
# --- LOCAL SETUP (replaces Colab-only %tensorflow_version / GPU check) ---
import os
os.environ["TF_USE_LEGACY_KERAS"] = "1"   # must be set BEFORE importing tensorflow
import tensorflow as tf
print("TensorFlow:", tf.__version__)
print("GPUs:", tf.config.list_physical_devices("GPU"), "(CPU is fine)")

QUICK = True   # True = 3 epochs per model (smoke test). Set False for full training.
def EP(n):
    return 3 if QUICK else n

TensorFlow: 2.21.0
GPUs: [] (CPU is fine)


In [7]:
import numpy as np
import math as ma
import plotly
import plotly.graph_objs as go
from random import randint
import pandas as pd
from sklearn import preprocessing
from sklearn.metrics import f1_score, recall_score, precision_score, roc_auc_score
from sklearn.preprocessing import MinMaxScaler,StandardScaler,normalize
from tensorflow.keras.models import Model, Sequential
from tensorflow.keras.layers import Lambda,add,Input,Conv1D,SeparableConv1D,BatchNormalization,LeakyReLU,Activation,Flatten,Dense,MaxPooling1D,LSTM,Dropout,GlobalAveragePooling1D,multiply,maximum,subtract
from tensorflow.keras import backend as K
from tensorflow.keras import metrics
from tensorflow.keras.callbacks import EarlyStopping,ModelCheckpoint
K.clear_session()

#Data generation

In [8]:
def operation(trajectories): #get the normal operation days
  normal_time=[] 
  for i in range(trajectories):
    health_period=randint(5, 15)#the machine operates in the health state for health_period,these machines appears fault and start sharply degradation after the health_period.
    normal_time.append(health_period)
  return normal_time

In [9]:
trajectories=200
normal_time=operation(trajectories)
kb=4*ma.sqrt(0.003)/(6*(1-0.3*0.3)/2.1e11)
ns=180
kdeg=1/((ma.pow(1/kb,2/3)+ma.pow(pow(ma.cos(20),5/2)/(ns*kb),2/3)))
kdeg1=1/((ma.pow(1/kb,2/3)+ma.pow(pow(ma.cos(20),5/2)/(kb),2/3)))
k1=(kdeg-kdeg1)/kdeg
print(k1)
kdeg2=[]
for i in range(120):
  k=1/((ma.pow(1/kb,2/3)+ma.pow(pow(ma.cos(20),5/2)/((150-i)*kb)*i,2/3)))
  kdeg2.append(k)
kdegas=go.Scatter(x=np.array(range(120)),y=np.array(kdeg2),mode='lines')
layout = go.Layout(xaxis=dict(title='Operations process(days)',showticklabels=True),yaxis=dict(title='Structure stiffiness(N/m^2)',showticklabels=True),paper_bgcolor='rgba(0,0,0,0)',plot_bgcolor='rgba(0,0,0,0)')
fig = go.Figure(data=kdegas, layout=layout)
fig.show()

0.17759899982927152


In [10]:
def stiffiness_caculation(normal):
  steps=1/400#piecewise degradation model,every day
  kb=4*ma.sqrt(0.003)/(6*(1-0.3*0.3)/2.1e11)
  ns=150
  kdeg1=1/((ma.pow(1/kb,2/3)+ma.pow(pow(ma.cos(20),5/2)/(ns*kb),2/3)))
  kdeg=kdeg1
  K =[] #Normal structure stiffiness
  # K_rub=int(normal//steps)*[0]#During the healthy state，no fault， no degradation
  time=[] #Rubbing stiffiness in health state
  i=1
  # kdeg=5000000#
  while kdeg> kdeg1/5:
    # Krub=3000000*(1+abs(np.random.normal(1, 0.5, None)))/pow((80-steps*i),3)#
    # kdeg=5000000-Krub-100*i#linear component and nolinear Krub
    kdeg=1/((ma.pow(1/kb,2/3)+ma.pow(pow(ma.cos(20),5/2)/(ns*kb)*steps*i,2/3)))
    kdeg=kdeg+np.random.normal(kdeg/10, kdeg/20, None)
    # Krub=kdeg1-kdeg
    ns=abs((150-steps*i))
    ns=ns+np.random.normal(ns/10, ns/20, None)
    time.append(normal+steps*i)
    K.append(kdeg)
    # K_rub.append(Krub)
    i=i+1
  return K,time #return the struc,K_rub

In [11]:
def stiffiness_degradation(normal_time):
  rubbing_stiffiness=[]
  structure_stiffiness=[]
  degradationdays=[]
  gap=100
  for kun in range(len(normal_time)):
    structure_stiff,time=stiffiness_caculation(normal_time[kun])#,rubbing_stiff
    # K_rub_at_monitoring_point=[]
    K_at_monitoring_point=[]
    days=[]
    for i in range(int(len(structure_stiff)/gap)):
      # K_rub_at_monitoring_point.append(rubbing_stiff[i*gap])#everyday 6 hours, 1/4800*800*24h,collect one sample
      K_at_monitoring_point.append(structure_stiff[i*gap])
      days.append(time[i*gap])
    # K_rub_at_monitoring_point.append(rubbing_stiff[-1])
    K_at_monitoring_point.append(structure_stiff[-1])
    days.append(time[-1])
    # rubbing_stiffiness.append(K_rub_at_monitoring_point)
    structure_stiffiness.append(K_at_monitoring_point)
    degradationdays.append(days)
  return structure_stiffiness,degradationdays#,rubbing_stiffiness

In [12]:
structure_stiffiness,degradationdays=stiffiness_degradation(normal_time[1:len(normal_time)])#get 100 degradation stiffiness

In [13]:
shui=[]
for i in structure_stiffiness:
  shui.append(i[-1])
structure_stiffiness_mean = np.mean(np.array(shui)) # 求方差 · 
structure_stiffiness_var = np.var(shui)
structure_stiffiness_std = np.std(shui)
print(format(structure_stiffiness_mean),format(structure_stiffiness_var),format(structure_stiffiness_std))

804334.7446221772 230999822.4737593 15198.678313384993


In [14]:
stiffiness=[]
days=[]
abnormal_position=[]
for i in range(len(structure_stiffiness)):
  kunun=structure_stiffiness[i][0]
  health_stiff=int(normal_time[i]*4)*[kunun]
  kunday=[normal_time[i]/4]*len(health_stiff)
  health_stiff.extend(structure_stiffiness[i])
  kunday.extend(degradationdays[i])
  stiffiness.append(health_stiff)
  days.append(kunday)
  abnormal_position.append(len(health_stiff))
print(stiffiness[1])

[4293787.577589219, 4293787.577589219, 4293787.577589219, 4293787.577589219, 4293787.577589219, 4293787.577589219, 4293787.577589219, 4293787.577589219, 4293787.577589219, 4293787.577589219, 4293787.577589219, 4293787.577589219, 4293787.577589219, 4293787.577589219, 4293787.577589219, 4293787.577589219, 4293787.577589219, 4293787.577589219, 4293787.577589219, 4293787.577589219, 4293787.577589219, 4293787.577589219, 4293787.577589219, 4293787.577589219, 4293787.577589219, 4293787.577589219, 4293787.577589219, 4293787.577589219, 4293787.577589219, 4293787.577589219, 4293787.577589219, 4293787.577589219, 4293787.577589219, 4293787.577589219, 4293787.577589219, 4293787.577589219, 4293787.577589219, 4260142.995032277, 4459978.995988116, 4556775.30969738, 4671922.693759198, 4674293.814739265, 4773542.916578458, 4481631.685803885, 4552148.183575288, 4228487.803144983, 4528723.180063, 4443553.069655507, 4670967.270858003, 4731427.796791973, 4612102.435518474, 4649107.803372109, 4674990.2408091

In [15]:
print(len(stiffiness[0]))
print(len(days[0]))

613
613


In [16]:
path="./data/"
os.makedirs(path, exist_ok=True)
stif_temp=[]
for i in range(len(stiffiness)):
  stif_temp.append(go.Scatter(x=days[i],y=np.array(stiffiness[i]),mode='lines'))
layout = go.Layout(xaxis=dict(title='Operations process(days)',showticklabels=True),yaxis=dict(title='Structure stiffiness(N/m^2)',showticklabels=True),paper_bgcolor='rgba(0,0,0,0)',plot_bgcolor='rgba(0,0,0,0)')
fig = go.Figure(data=stif_temp, layout=layout)
fig.show()

In [17]:
stif_temp1=go.Scatter(x=days[1],y=np.array(stiffiness[10]),mode='lines')
layout = go.Layout(xaxis=dict(title='Operations process(days)',showticklabels=True),yaxis=dict(title='Structure stiffiness(N/m^2)',showticklabels=True),paper_bgcolor='rgba(0,0,0,0)',plot_bgcolor='rgba(0,0,0,0)')
fig = go.Figure(data=stif_temp1, layout=layout)
fig.show()

In [18]:
e=5/2500*(10/100)#system unbalance mass（kg），it is excitation
m= 5#Take the equivalent mass of the system as 5 kg
speed=2*3.14*70#rotation speed is 12000rpm, and its round frequency is 2*pi*f
Amp=[]#get the vibration amp at each stiffness_degradation point.
for kun in range(len(stiffiness)):
  amp=[]
  for i in range(len(stiffiness[kun])):
    stiff_temp=pow(np.array(stiffiness[kun][i]/m),0.5)
    d_amp=e*speed**2/(abs(stiff_temp**2-speed**2))
    amp.append(d_amp)
  Amp.append(amp)

In [19]:
Amp_temp=[]
for i in range(len(stiffiness)):
  Amp_temp.append(go.Scatter(x=degradationdays[i],y=np.array(Amp[i]),mode='lines'))
layout = go.Layout(xaxis=dict(title='Operations process(days)',showticklabels=True),yaxis=dict(title='Vibration peak(m)',showticklabels=True),paper_bgcolor='rgba(0,0,0,0)',plot_bgcolor='rgba(0,0,0,0)')
fig = go.Figure(data=Amp_temp, layout=layout)
fig.show()

In [20]:
ground_truth=[]
for i in range(len(days)):
  ground_truth.append([max(days[i])-x+0.5 for x in days[i]])
RUL=ground_truth

In [21]:
# 
# # Amp_piece=[]
# lif=[] #find the abnoraml point 
# for i in range(trajectories):
#   position=np.nonzero(rubbing_stiffiness[i])
#   abnormal_position.append(position[0][0])#find the abnormal point
#   lif.append(degradationdays[i][-1]-degradationdays[i][position[0][0]])
# life=np.median(lif)

In [22]:

# # operation_days=[]
# R1=[]
# for i in range(trajectories):
#   kun=degradationdays[i][abnormal_position[i]]
#   R1=[1  for x in degradationdays[i][0:abnormal_position[i]]]
#   R1.extend([1-abs((x-kun))/life for x in degradationdays[i][abnormal_position[i]:]])
#   R1 = [0 if x<0 else x for x in R1]
#   R1 = [life*x for x in R1]
#   # R1[0:abnormal_position[i]]=[1]*abnormal_position[i]
#   RUL.append(R1)

In [23]:
from scipy import stats
def Timefeature(data):
   #mean
   df_mean=data.mean()
        #var 
   df_var=data.var() 
        #min。max 
   df_max=max(data)
   df_maxmin=(max(data))-(min(data))
        #str
   df_std=data.std()
        #rmse 
   df_rms=ma.sqrt(pow(df_mean,2) + pow(df_std,2))
        #skew 
   df_skew=stats.skew(data)
        #kurtosis 
   df_kurt=stats.kurtosis(data)
   sum=0
   for i in range(len(data)):
     sum+=ma.sqrt(abs(data[i]))
            #wave_factor 
   df_boxing=df_rms / (abs(data).mean())
        #peak_factor 
   df_fengzhi=(max(data)) / df_rms
        #Impulse_factor 
   df_maichong=(max(data)) / (abs(data).mean())
        #Margin factor 
   df_yudu=(max(data)) / pow((sum/len(data)),2)
   df_phy1=pow(speed,2)/max(data)
   featuretime_list = [df_mean,df_var,df_max,df_maxmin,df_rms,df_skew,df_kurt,df_boxing,df_fengzhi,df_maichong,df_yudu,df_phy1]
   return featuretime_list

In [24]:
def Add_noise(x, snr):
    len_x = len(x)
    Ps = np.sum(np.power(x, 2)) / len_x
    Pn = Ps / (np.power(20, snr / 10))
    noise = np.random.randn(len_x) * np.sqrt(Pn)
    return x + noise

In [25]:
Data=[]
# Time_feature=[]
t=np.linspace(0,1,2048*3)
lkun=len(t)
speed=2*3.14*70
for kun in range(len(days)):
  data=[]
  # feature=[]
  for i1 in range(abnormal_position[kun]):
    # ni=abs(np.random.normal(Amp[kun][i1]/10, Amp[kun][i1]/2, None))
    vib=(Amp[kun][i1])*np.sin(speed*t)#unstable fault component
    x_temp=Add_noise(vib,0.5)
    data.append(x_temp)
    # feature.append(Timefeature(abs(x_temp)))
  for i in range(abnormal_position[kun],len(Amp[kun])):
    # ni=abs(np.random.normal(Amp[kun][i]/10, Amp[kun][i]/2, None))
    vib=(Amp[kun][i])*np.sin(speed*t)+(Amp[kun][i])*np.sin(speed*((1+abs(np.random.normal(4, 2, None))*t)))
    x_temp=Add_noise(vib,2)
    data.append(x_temp)#unstable fault component
    # feature.append(Timefeature(abs(x_temp)))
  Data.append(data)
  # Time_feature.append(np.array(feature).T)

#Data preparation
running windows=1
ground truth rul
Only 11 time statistics feature


In [26]:
def split_train_val(length,val_ratio):
    np.random.seed(length)#Randomly divide the training and validation sets
    shuffled_indices = np.random.permutation(length)
    val_set_size = int(len(shuffled_indices) * (1-val_ratio))
    shuffled_indices1=shuffled_indices[0:val_set_size]
    shuffled_indices2=shuffled_indices[val_set_size:]
    return shuffled_indices1,shuffled_indices2
shuffled_indices1,shuffled_indices2=split_train_val(150,0.6)#train：val=4：1
X_train=[]
X_Vali=[]
RUL_train=[]
RUL_vali=[]
RUL_train_g=[]
RUL_vali_g=[]
for i in range(len(shuffled_indices1)):
  RUL_train.append(RUL[shuffled_indices1[i]])
  RUL_train_g.append(ground_truth[shuffled_indices1[i]])
  X_train.append(Data[shuffled_indices1[i]])
for i in range(len(shuffled_indices2)):
  RUL_vali.append(RUL[shuffled_indices2[i]])
  RUL_vali_g.append(ground_truth[shuffled_indices2[i]])
  X_Vali.append(Data[shuffled_indices2[i]])
X_test=Data[150:]
RUL_test=RUL[150:]
RUL_test_g=ground_truth[150:]

In [27]:
print(RUL_train[1])
print(RUL_train_g[1])

[155.9775, 155.9775, 155.9775, 155.9775, 155.9775, 155.9775, 155.9775, 155.9775, 155.9775, 155.9775, 155.9775, 155.9775, 155.9775, 155.9775, 155.9775, 155.9775, 155.9775, 155.9775, 155.9775, 155.9775, 155.9775, 155.9775, 155.9775, 155.9775, 155.9775, 155.9775, 155.9775, 155.9775, 155.9775, 155.9775, 155.9775, 155.9775, 155.9775, 155.9775, 155.9775, 155.9775, 155.9775, 155.9775, 155.9775, 155.9775, 155.9775, 155.9775, 155.9775, 155.9775, 148.725, 148.475, 148.225, 147.975, 147.725, 147.475, 147.225, 146.975, 146.725, 146.475, 146.225, 145.975, 145.725, 145.475, 145.225, 144.975, 144.725, 144.475, 144.225, 143.975, 143.725, 143.475, 143.225, 142.975, 142.725, 142.475, 142.225, 141.975, 141.725, 141.475, 141.225, 140.975, 140.725, 140.475, 140.225, 139.975, 139.725, 139.475, 139.225, 138.975, 138.725, 138.475, 138.225, 137.975, 137.725, 137.475, 137.225, 136.975, 136.725, 136.475, 136.225, 135.975, 135.725, 135.475, 135.225, 134.975, 134.725, 134.475, 134.225, 133.975, 133.725, 133.475, 1

In [28]:
RUL_temp=[]
for i in range(len(days)):
  RUL_temp.append(go.Scatter(x=days[i],y=np.array(ground_truth[i]),mode='lines'))
layout = go.Layout(xaxis=dict(title='Operations process(days)',showticklabels=True),yaxis=dict(title='RUL ',showticklabels=True),paper_bgcolor='rgba(0,0,0,0)',plot_bgcolor='rgba(0,0,0,0)')
fig = go.Figure(data=RUL_temp, layout=layout)
fig.show()

In [29]:
# def cut(data):
#   kun=[]
#   for i in range(int(len(data)/(4096*3)-1)):
#     kun.append(Timefeature(data[i*(4096*3):(i+1)*(4096*3))])
#   return kun
def cut(Data):
  kun=[]
  for i in range(len(Data)):
    kun.append(Timefeature(Data[i]))
  return kun
# print(X_train[1][2])
Train=[]
for i in range(len(X_train)):
  Train.append(cut(X_train[i]))
Vali=[]
for i in range(len(X_Vali)):
  Vali.append(cut(X_Vali[i]))
Test=[]
for i in range(len(X_test)):
  Test.append(cut(X_test[i]))

In [30]:
# def create_dataset(data,label,sql):
#     dataX,dataY = [],[]
#     for i in range(len(data)-sql-1):
#         a = np.array(data)[i:(i+sql)]
#         dataX.append(a)
#         dataY.append(label[i+sql])
#     return np.array(dataX),np.array(dataY)
def gen_sequence(data,label,seq_length):
  num_elements = len(data)
  min_max_scaler = preprocessing.MinMaxScaler()
  l = min_max_scaler.fit_transform(data)
  # l=normalize(data, norm="l2", axis=0)
  kun=[]
  kunkun=[]
  for start, stop in zip(range(0, num_elements - seq_length), range(seq_length, num_elements)):
    kun.append(l[start:stop])
    kunkun.append(label[stop])
  return kun,kunkun

In [31]:
train=[]
rultrain=[]
rultrain_g=[]
sql=30
for i in range(len(Train)):
  dataX,dataY=gen_sequence(np.array(Train[i]),np.array(RUL_train[i]),sql)
  _,dataY_g=gen_sequence(np.array(Train[i]),np.array(RUL_train_g[i]),sql)
  train.extend(dataX)
  rultrain.extend(dataY)
  rultrain_g.extend(dataY_g)
vali=[]
rulvali=[]
rulvali_g=[]
for i in range(len(Vali)):
  dataX,dataY=gen_sequence(np.array(Vali[i]),RUL_vali[i],sql)
  _,dataY_g=gen_sequence(np.array(Vali[i]),RUL_vali_g[i],sql)
  vali.extend(dataX)
  rulvali.extend(dataY)
  rulvali_g.extend(dataY_g)
test=[]
rultest=[]
rultest_g=[]
for i in range(len(Test)):
  dataX,dataY=gen_sequence(np.array(Test[i]),RUL_test[i],sql)
  _,dataY_g=gen_sequence(np.array(Test[i]),RUL_test_g[i],sql)
  test.extend(dataX)
  rultest.extend(dataY)
  rultest_g.extend(dataY_g)

#Algorithm design 
Lightweight Resblock and
Customer design layer

In [32]:
def h_swish(inputs):
    return inputs * tf.nn.relu6(inputs + 3) / 6
def swish(inputs):
    return (K.sigmoid(inputs) * inputs)
tf.keras.utils.get_custom_objects().update({'swish': Activation(swish)})    
tf.keras.utils.get_custom_objects().update({'h_swish': Activation(h_swish)})

In [33]:
def ResBlock(x,filters,kernel_size,dilation_rate,strides):
  r=BatchNormalization()(x)
  r=LeakyReLU(alpha=0.2)(r)#Randomly set values，make no sense
  r=SeparableConv1D(filters,kernel_size,padding='causal',dilation_rate=dilation_rate,activation='relu')(r)
  r=BatchNormalization()(r) 
  r=Dropout(0.4)(r)#Randomly set values，make no sense
  r=SeparableConv1D(filters,kernel_size,padding='causal',dilation_rate=dilation_rate,activation='relu')(r) 
  if x.shape[-1]==filters:
    shortcut=x
  else:
    shortcut=SeparableConv1D(filters,kernel_size,padding='causal',activation='relu')(x)  
  o=add([r,shortcut])
  o=Activation('relu')(o)  
  return o

###The relationship between vibration amplitude and stiffness is extracted using a custom layer, which reflects the mathematical relationship：


1.（Ω^2/max（Amp）+Ω^2）×m=Stiffiness（m is Equivalent mass,Ω is the rotation speed）
 
2. hope this layer can learn the relation between Ω^2/max（Amp），m×Ω^2 and Stiffiness

3. m*Ω^2 is Parameters to be determined， in the layer， it is represented by self.b, and self.w represents the fitting of m×Ω^2/max（Amp）




In [34]:
from tensorflow.keras.layers import Layer
class MyLayer(Layer):
  def __init__(self,units,speed,**kwargs):
    self.units = units
    self.speed = speed
    # self.speed = speed
    super(MyLayer, self).__init__(**kwargs)
  def build(self, input_shape):
    self.kernel = self.add_weight(name='kernel',shape=(input_shape[1], self.units),initializer='uniform',trainable=True)
    super(MyLayer, self).build(input_shape) 
    # self.w = self.add_weight(shape=(input_shape[1],), initializer="uniform", trainable=True)
    # self.b = self.add_weight(shape=(self.units,), initializer="uniform", trainable=True)
  def call(self, x):
    # L1=K.abs(tf.math.reciprocal_no_nan(x*self.speed*self.speed+self.speed*self.speed))
    # # L1=tf.math.reciprocal_no_nan(L1)
    L1=tf.math.reciprocal(K.dot(tf.math.reciprocal(x)*self.speed*self.speed+self.speed*self.speed, self.kernel))
    # L1=L1
    # L1=K.dot(, self.kernel)
    # x=tf.abs(x)+tf.math.reduce_mean(tf.abs(x))
    # L1=self.w*tf.math.reciprocal_no_nan(x)+self.b
    # L1=self.speed**2*L1 
    return L1*tf.nn.relu6(L1+3)/6# similar to the physics informed feature， but here using
  def compute_output_shape(self, input_shape):
    return (input_shape[0], self.units)
  def get_config(self):
    config = super().get_config().copy()
    config.update({'units': self.units})
    return config


In [35]:
def rmse(y_true, y_pred):
    return K.sqrt(K.mean(K.square(y_pred - y_true), axis=-1))

#Model training

##Raw data

In [36]:
def nophy0(data):
  k=[]
  l=[]
  for i in range(len(data)):
    l1=data[i][0:10]
    # l2=data[i][6:13]
    k.append(np.hstack(l1))
  return k
train0=[]
vali0=[]
test0=[]
for i in range(len(train)):
  train0.append(nophy0(train[i]))
for i in range(len(vali)):
  vali0.append(nophy0(vali[i]))
for i in range(len(test)):
  test0.append(nophy0(test[i]))

##Data with PI feature

In [37]:
def nophy1(data):
  k=[]
  l=[]
  for i in range(len(data)):
    l1=data[i][1:6]
    l2=data[i][6:13]
    k.append(np.hstack([l1,l2]))
  return k
train1=[]
vali1=[]
test1=[]
for i in range(len(train)):
  train1.append(nophy1(train[i]))
for i in range(len(vali)):
  vali1.append(nophy1(vali[i]))
for i in range(len(test)):
  test1.append(nophy1(test[i]))

##Model：purely data driven




In [38]:
from tensorflow.keras.callbacks import ReduceLROnPlateau
inputs=Input(shape=(sql,10))  
x=tf.keras.layers.Reshape((10,sql))(inputs)
x=ResBlock(inputs,filters=32,kernel_size=3,dilation_rate=1,strides=1)
# x=ResBlock(x,filters=32,kernel_size=3,dilation_rate=2,strides=2)
x=ResBlock(x,filters=16,kernel_size=3,dilation_rate=4,strides=2)
# x = Conv1D(32,3,strides=2,padding='causal')(inputs)
# x = MaxPooling1D(4)(x)
# x = Dropout(0.4)(x)
# # x=MaxPooling1D(8)(x)
# x=ResBlock(x,filters=32,kernel_size=2,dilation_rate=1,strides=1)
# x=ResBlock(x,filters=16,kernel_size=2,dilation_rate=1,strides=1)
x = GlobalAveragePooling1D()(x)
#x = Dense(8)(x)
#x = Dense(4)(x)
reduce_lr = ReduceLROnPlateau(monitor='val_rmse', patience=20, mode='auto')
outputs = Dense(1,activation ='h_swish')(x)
model = Model(inputs=inputs, outputs=outputs)
model.compile(optimizer='adam',loss='mean_squared_error',metrics=[rmse])
model.summary()
filepath=path+"weights.best.hdf5"
my_callbacks = [
        # RocAucMetricCallback(),  # include it before EarlyStopping!
        EarlyStopping(monitor='val_rmse', patience=50, verbose=2, mode='min')
    ]
checkpoint = ModelCheckpoint(filepath, monitor='val_rmse', verbose=1, save_best_only=True,mode='min',save_weights_only=True)
callbacks_list = [checkpoint]+my_callbacks#,my_callbacks


Model: "model"
__________________________________________________________________________________________________
 Layer (type)                Output Shape                 Param #   Connected to                  
 input_1 (InputLayer)        [(None, 30, 10)]             0         []                            
                                                                                                  
 batch_normalization (Batch  (None, 30, 10)               40        ['input_1[0][0]']             
 Normalization)                                                                                   
                                                                                                  
 leaky_re_lu (LeakyReLU)     (None, 30, 10)               0         ['batch_normalization[0][0]'] 
                                                                                                  
 separable_conv1d (Separabl  (None, 30, 32)               382       ['leaky_re_lu[0][0]']    

In [39]:
history=model.fit(np.array(train0),np.array(rultrain),batch_size=64,epochs=EP(400),validation_data=(np.array(vali0),np.array(rulvali)),callbacks=callbacks_list)#,callbacks=[reduce_lr]

Epoch 1/3


557/565 [============================>.] - ETA: 0s - loss: 2288.9360 - rmse: 35.5446
Epoch 1: val_rmse improved from inf to 30.41367, saving model to ./data\weights.best.hdf5
565/565 [==============================] - 9s 11ms/step - loss: 2270.7380 - rmse: 35.3923 - val_loss: 1332.6794 - val_rmse: 30.4137
Epoch 2/3
558/565 [============================>.] - ETA: 0s - loss: 560.5943 - rmse: 18.4610
Epoch 2: val_rmse improved from 30.41367 to 17.02035, saving model to ./data\weights.best.hdf5
565/565 [==============================] - 6s 10ms/step - loss: 557.5451 - rmse: 18.4022 - val_loss: 601.3962 - val_rmse: 17.0203
Epoch 3/3
563/565 [============================>.] - ETA: 0s - loss: 309.7888 - rmse: 13.2585
Epoch 3: val_rmse improved from 17.02035 to 14.55179, saving model to ./data\weights.best.hdf5
565/565 [==============================] - 6s 10ms/step - loss: 309.9939 - rmse: 13.2624 - val_loss: 536.8990 - val_rmse: 14.5518


##Model1：data driven ML with phy-extras layer

In [40]:
def preresult(model0,test0):
  pre0=model0.predict(np.array(test0))
  result0=[]
  for i in range(len(pre0)):
    result0.extend(pre0[i])
    xasix=list(range(len(result0)))
  # print(rultest)
  # print(result0)
  # print(xasix)
  x1=go.Scatter(x=xasix,y=rultest_g,marker_symbol='triangle-down-open-dot',marker_size=4,mode='markers',name='Real Rul')
  x2=go.Scatter(x=xasix,y=result0,mode='markers',marker_size=4,name='Prediction Rul')
  layout = go.Layout(xaxis=dict(title='Test samples in each trajectory',showticklabels=True),yaxis=dict(title='Rul(days)',showticklabels=True),paper_bgcolor='rgba(0,0,0,0)',plot_bgcolor='rgba(0,0,0,0)')
  fig = go.Figure(data=[x1,x2], layout=layout)
  fig.show()
  return xasix,pre0
# print(filepath)
# model.load_weights(filepath)

In [41]:
def preresult1(model0,test0):
  pre0=model0.predict(np.array(test0))
  result0=[]
  for i in range(len(pre0)):
    result0.extend(pre0[i])
    xasix=list(range(len(result0)))
  # print(rultest)
  # print(result0)
  # print(xasix)
  x1=go.Scatter(x=xasix,y=np.array(result0)-np.array(rultest_g),marker_symbol='triangle-down-open-dot',marker_size=4,mode='markers')
  x2=go.Scatter(x=xasix,y=result0,mode='markers',marker_size=4,name='Prediction Rul')
  layout = go.Layout(xaxis=dict(title='Test samples in each trajectory',showticklabels=True),yaxis=dict(title='Rul prediction error — y_pre-r_real(days)',showticklabels=True),paper_bgcolor='rgba(0,0,0,0)',plot_bgcolor='rgba(0,0,0,0)')
  fig = go.Figure(data=x1, layout=layout)
  fig.show()
  return xasix,pre0

In [42]:
# class Dense_with_Center_loss(Layer):
#   def __init__(self, output_dim, **kwargs):
#     self.output_dim = output_dim
#     super(Dense_with_Center_loss, self).__init__(**kwargs)
#   def build(self, input_shape):
#     self.kernel = self.add_weight(name='kernel',shape=(input_shape[1], self.output_dim),initializer='glorot_normal',trainable=True)
#     self.bias = self.add_weight(name='bias',shape=(self.output_dim,),initializer='zeros',trainable=True)
#     self.centers = self.add_weight(name='centers',shape=(self.output_dim, input_shape[1]),initializer='glorot_normal',trainable=True)
#   def call(self, inputs):
#     self.inputs = inputs
#     return K.dot(inputs, self.kernel) + self.bias 
#   def compute_output_shape(self, input_shape):
#     return (input_shape[0], self.output_dim)
#   def loss(self, y_true, y_pred, lamb=0.5):
#     y_true = K.cast(y_true, 'int32') 
#     crossentropy = K.sparse_categorical_crossentropy(y_true, y_pred, from_logits=True)
#     centers = K.gather(self.centers, y_true[:, 0]) 
#     center_loss = K.sum(K.square(centers - self.inputs), axis=1)  
#     return crossentropy + lamb * center_loss

In [43]:
def slice(x,index):
  return x[:,:,index]

In [44]:
from tensorflow.keras.callbacks import ReduceLROnPlateau
inputs=Input(shape=(sql,10))
r = Lambda(slice,output_shape=(sql,1),arguments={'index':1})(inputs)
r = MyLayer(sql,speed)(r)
r=tf.keras.layers.Reshape((1,sql))(r)
# r = Dense(16,activation ='h_swish')(r)
# r=reshape(20,1)  
x = Conv1D(sql,3,strides=2,padding='causal')(inputs)
x = Dropout(0.4)(x)
x = tf.keras.layers.Concatenate(axis=1)([x, r])
# x=MaxPooling1D(8)(x)
x=ResBlock(x,filters=12,kernel_size=2,dilation_rate=1,strides=1)
x=ResBlock(x,filters=4,kernel_size=2,dilation_rate=1,strides=1)
# x=ResBlock(x,filters=4,kernel_size=2,dilation_rate=1,strides=1)# x=Conv1D(filters=16,kernel_size=2,padding='same',dilation_rate=4,activation='relu',kernel_initializer='orthogonal',
#                 bias_initializer='zeros')(x)   
x = GlobalAveragePooling1D()(x)
#x = Dense(8)(x)
#x = Dense(4)(x)
reduce_lr = ReduceLROnPlateau(monitor='val_rmse',factor=0.4,patience=20, mode='auto')
outputs = Dense(1,activation ='h_swish')(x)
model1 = Model(inputs=inputs, outputs=outputs)
model1.compile(optimizer='adam',loss='mean_squared_error',metrics=[rmse])
model1.summary()
filepath1=path+"weights1.best.hdf5"
my_callbacks = [
        # RocAucMetricCallback(),  # include it before EarlyStopping!
        EarlyStopping(monitor='val_rmse', patience=50, verbose=2, mode='min')
    ]
checkpoint = ModelCheckpoint(filepath1, monitor='val_rmse', verbose=1, save_best_only=True,mode='min',save_weights_only=True)
callbacks_list = [checkpoint]+my_callbacks#,my_callbacks,reduce_lr

Model: "model_1"
__________________________________________________________________________________________________
 Layer (type)                Output Shape                 Param #   Connected to                  
 input_2 (InputLayer)        [(None, 30, 10)]             0         []                            
                                                                                                  
 lambda (Lambda)             (None, 30)                   0         ['input_2[0][0]']             
                                                                                                  
 conv1d (Conv1D)             (None, 15, 30)               930       ['input_2[0][0]']             
                                                                                                  
 my_layer (MyLayer)          (None, 30)                   900       ['lambda[0][0]']              
                                                                                            

In [45]:
history1=model1.fit(np.array(train0),np.array(rultrain),batch_size=128,epochs=EP(400),validation_data=(np.array(vali0),np.array(rulvali)),callbacks=callbacks_list)#,callbacks=[reduce_lr]

Epoch 1/3
279/283 [============================>.] - ETA: 0s - loss: nan - rmse: nan
Epoch 1: val_rmse did not improve from inf
283/283 [==============================] - 5s 10ms/step - loss: nan - rmse: nan - val_loss: nan - val_rmse: nan
Epoch 2/3
282/283 [============================>.] - ETA: 0s - loss: nan - rmse: nan
Epoch 2: val_rmse did not improve from inf
283/283 [==============================] - 3s 9ms/step - loss: nan - rmse: nan - val_loss: nan - val_rmse: nan
Epoch 3/3
279/283 [============================>.] - ETA: 0s - loss: nan - rmse: nan
Epoch 3: val_rmse did not improve from inf
283/283 [==============================] - 3s 10ms/step - loss: nan - rmse: nan - val_loss: nan - val_rmse: nan


##Model 2: feature layer and another layer
data driven ML with phy-extras layer， after the phy-layer， add another linear layer to convert the non-linear output into linear pseudo-rul predicted values

In [46]:
# def ResBlock1(x,x1,filters,kernel_size,dilation_rate,strides):
#   r=BatchNormalization()(x)
#   r=LeakyReLU(alpha=0.2)(r)#Randomly set values，make no sense
#   r=SeparableConv1D(filters,kernel_size,padding='causal',dilation_rate=dilation_rate,activation='relu')(r)
#   r=BatchNormalization()(r) 
#   r=Dropout(0.3)(r)#Randomly set values，make no sense
#   r=SeparableConv1D(filters,kernel_size,padding='causal',dilation_rate=dilation_rate,activation='relu')(r) 
#   if x.shape[-1]==filters:
#     shortcut=x
#   else:
#     shortcut=SeparableConv1D(filters,kernel_size,padding='causal',activation='relu')(x)  
#   o=add([r,shortcut])
#   o=Activation('h_swish')(o)  
#   return o

In [47]:
from tensorflow.keras.callbacks import ReduceLROnPlateau
inputs=Input(shape=(sql,10))  
r = Lambda(slice,output_shape=(1,sql),arguments={'index':1})(inputs)  
r = MyLayer(sql,speed)(r)
x=tf.keras.layers.Reshape((10,sql))(inputs)
x = add([x, r])
x=ResBlock(inputs,filters=32,kernel_size=3,dilation_rate=1,strides=1)
# x=ResBlock(x,filters=32,kernel_size=3,dilation_rate=2,strides=2)
x=ResBlock(x,filters=16,kernel_size=3,dilation_rate=4,strides=2)
# x = Conv1D(32,3,strides=2,padding='causal')(inputs)
# x = MaxPooling1D(4)(x)
# x = Dropout(0.4)(x)
# # x=MaxPooling1D(8)(x)
# x=ResBlock(x,filters=32,kernel_size=2,dilation_rate=1,strides=1)
# x=ResBlock(x,filters=16,kernel_size=2,dilation_rate=1,strides=1)
x = GlobalAveragePooling1D()(x)
#x = Dense(8)(x)
#x = Dense(4)(x)
outputs = Dense(1,activation ='h_swish')(x)
model2 = Model(inputs=inputs, outputs=outputs)
model2.compile(optimizer='adam',loss='mean_squared_error',metrics=[rmse])
model2.summary()
filepath2=path+"weights2.best.hdf5"
my_callbacks = [
        # RocAucMetricCallback(),  # include it before EarlyStopping!
        EarlyStopping(monitor='val_rmse', patience=60, verbose=2, mode='min')
    ]
checkpoint = ModelCheckpoint(filepath2, monitor='val_rmse', verbose=1, save_best_only=True,mode='min',save_weights_only=True)

Model: "model_2"
__________________________________________________________________________________________________
 Layer (type)                Output Shape                 Param #   Connected to                  
 input_3 (InputLayer)        [(None, 30, 10)]             0         []                            
                                                                                                  
 batch_normalization_8 (Bat  (None, 30, 10)               40        ['input_3[0][0]']             
 chNormalization)                                                                                 
                                                                                                  
 leaky_re_lu_4 (LeakyReLU)   (None, 30, 10)               0         ['batch_normalization_8[0][0]'
                                                                    ]                             
                                                                                            

In [48]:
from tensorflow.keras.callbacks import Callback
class StepLR(Callback):
  def __init__(self, lr_list, epoch_list, verbose=1):
    super().__init__()
    self.lr_list = lr_list
    self.epoch_list = epoch_list
    self.verbose = verbose

  def on_epoch_begin(self, epoch, logs=None):
    if epoch < self.epoch_list[0]:
      K.set_value(self.model.optimizer.lr, self.lr_list[0])
    elif epoch == self.epoch_list[0]:
      self.lr_list.pop(0)
      self.epoch_list.pop(0)
      K.set_value(self.model.optimizer.lr, self.lr_list[0])
    if self.verbose > 0:
      print('\nEpoch %05d: LearningRate''is %s.' % (epoch + 1, K.get_value(self.model.optimizer.lr)))

  def on_epoch_end(self, epoch, logs=None):
    logs = logs or {}
    logs['lr'] = K.get_value(self.model.optimizer.lr)
epoch_list = [100, 200, 400]
lr_list    = [0.1, 0.05, 0.01]
stepLR = StepLR(lr_list, epoch_list)
callbacks_list = [checkpoint]+my_callbacks#,my_callbacks,my_callbacks

In [49]:
history2=model2.fit(np.array(train0),np.array(rultrain),batch_size=64,epochs=EP(900),validation_data=(np.array(vali0),np.array(rulvali)),callbacks=callbacks_list)#,callbacks=[reduce_lr]

Epoch 1/3
564/565 [============================>.] - ETA: 0s - loss: 2179.2644 - rmse: 34.0903
Epoch 1: val_rmse improved from inf to 28.67159, saving model to ./data\weights2.best.hdf5
565/565 [==============================] - 8s 10ms/step - loss: 2177.3201 - rmse: 34.0740 - val_loss: 1135.2789 - val_rmse: 28.6716
Epoch 2/3
559/565 [============================>.] - ETA: 0s - loss: 471.4514 - rmse: 16.7368
Epoch 2: val_rmse did not improve from 28.67159
565/565 [==============================] - 6s 10ms/step - loss: 470.6881 - rmse: 16.7183 - val_loss: 2207.3613 - val_rmse: 35.2275
Epoch 3/3
559/565 [============================>.] - ETA: 0s - loss: 320.0650 - rmse: 13.4231
Epoch 3: val_rmse did not improve from 28.67159
565/565 [==============================] - 6s 10ms/step - loss: 319.5170 - rmse: 13.4143 - val_loss: 2261.4387 - val_rmse: 35.6980


##Model 3：Dual_loss，Physics output and the CNN output

In [50]:
from tensorflow.keras.callbacks import ReduceLROnPlateau
inputs=Input(shape=(sql,10))  
r = Lambda(slice,output_shape=(1,sql),arguments={'index':1})(inputs)  
r = MyLayer(sql,speed)(r)
x=tf.keras.layers.Reshape((10,sql))(inputs)
x = add([x, r])
x=ResBlock(inputs,filters=32,kernel_size=3,dilation_rate=1,strides=1)
# x=ResBlock(x,filters=32,kernel_size=3,dilation_rate=2,strides=2)
x=ResBlock(x,filters=16,kernel_size=3,dilation_rate=4,strides=2)
x = GlobalAveragePooling1D()(x)
# r = GlobalAveragePooling1D()(r)
r_out = Dense(1,activation ='h_swish',name='aus_out')(r)
# r = Dense(1,activation ='sigmoid')(r)
# r=reshape(20,1)  
# x = Conv1D(15,3,strides=2,padding='causal')(inputs)
# x = Dropout(0.4)(x)
# # r_out=tf.keras.layers.Reshape((1,16))(r_out)
# r=tf.keras.layers.Reshape((1,15))(r)
# x = tf.keras.layers.Concatenate(axis=1)([x, r])
# # x=MaxPooling1D(8)(x)
# x=ResBlock(x,filters=12,kernel_size=2,dilation_rate=1,strides=1)
# x=ResBlock(x,filters=4,kernel_size=2,dilation_rate=1,strides=1)# x=Conv1D(filters=16,kernel_size=2,padding='same',dilation_rate=4,activation='relu',kernel_initializer='orthogonal',
# #                 bias_initializer='zeros')(x)   
# x = GlobalAveragePooling1D()(x)
# # l_out = Dense(1,activation ='h_swish',name='aus_output')(r_out)
# #x = Dense(8)(x)
# #x = Dense(4)(x)
x_out= Dense(1,activation ='h_swish',name='main_output')(x)
outputs=[x_out,r_out] 
model3 = Model(inputs=inputs, outputs=outputs)
model3.compile(optimizer='adam',loss='mean_squared_error',loss_weights=[1., 0.2],metrics=[rmse])
model3.summary()
filepath3=path+"weights3.best.hdf5"
my_callbacks = [
        # RocAucMetricCallback(),  # include it before EarlyStopping!
        EarlyStopping(monitor='val_main_output_rmse', patience=50, verbose=2, mode='min')
    ]
checkpoint = ModelCheckpoint(filepath3, monitor='val_main_output_rmse', verbose=1, save_best_only=True,mode='min',save_weights_only=True)
callbacks_list = [checkpoint]+my_callbacks#

Model: "model_3"
__________________________________________________________________________________________________
 Layer (type)                Output Shape                 Param #   Connected to                  
 input_4 (InputLayer)        [(None, 30, 10)]             0         []                            
                                                                                                  
 batch_normalization_12 (Ba  (None, 30, 10)               40        ['input_4[0][0]']             
 tchNormalization)                                                                                
                                                                                                  
 leaky_re_lu_6 (LeakyReLU)   (None, 30, 10)               0         ['batch_normalization_12[0][0]
                                                                    ']                            
                                                                                            

In [51]:
history3=model3.fit(np.array(train0),[np.array(rultrain),np.array(rultrain)],batch_size=64,epochs=EP(400),validation_data=(np.array(vali0),[np.array(rulvali),np.array(rulvali)]),callbacks=callbacks_list)#,callbacks=[reduce_lr]

Epoch 1/3
564/565 [============================>.] - ETA: 0s - loss: nan - main_output_loss: 2255.5698 - aus_out_loss: nan - main_output_rmse: 34.6344 - aus_out_rmse: nan
Epoch 1: val_main_output_rmse improved from inf to 29.79062, saving model to ./data\weights3.best.hdf5
565/565 [==============================] - 9s 11ms/step - loss: nan - main_output_loss: 2253.3853 - aus_out_loss: nan - main_output_rmse: 34.6154 - aus_out_rmse: nan - val_loss: nan - val_main_output_loss: 1411.6482 - val_aus_out_loss: nan - val_main_output_rmse: 29.7906 - val_aus_out_rmse: nan
Epoch 2/3
564/565 [============================>.] - ETA: 0s - loss: nan - main_output_loss: 441.0794 - aus_out_loss: nan - main_output_rmse: 16.2496 - aus_out_rmse: nan
Epoch 2: val_main_output_rmse improved from 29.79062 to 20.38147, saving model to ./data\weights3.best.hdf5
565/565 [==============================] - 6s 10ms/step - loss: nan - main_output_loss: 441.0376 - aus_out_loss: nan - main_output_rmse: 16.2479 - aus_o


##Model 4: physics features


In [52]:
inputs=Input(shape=(sql,11))     
x = Conv1D(16,3,strides=2,padding='causal')(inputs)
x = Dropout(0.4)(x)
# x=MaxPooling1D(8)(x)
x=ResBlock(x,filters=12,kernel_size=2,dilation_rate=1,strides=1)
x=ResBlock(x,filters=4,kernel_size=2,dilation_rate=1,strides=1)# x=Conv1D(filters=16,kernel_size=2,padding='same',dilation_rate=4,activation='relu',kernel_initializer='orthogonal',
#                 bias_initializer='zeros')(x)   
x = GlobalAveragePooling1D()(x)
#x = Dense(8)(x)
#x = Dense(4)(x)
outputs = Dense(1,activation ='h_swish')(x)
model4 = Model(inputs=inputs, outputs=outputs)
model4.compile(optimizer='adam',loss='mean_squared_error',metrics=[rmse])
model4.summary()
filepath4=path+"weights4.best.hdf5"
my_callbacks = [
        # RocAucMetricCallback(),  # include it before EarlyStopping!
        EarlyStopping(monitor='val_rmse', patience=50, verbose=2, mode='min')
    ]
checkpoint = ModelCheckpoint(filepath4, monitor='val_rmse', verbose=1, save_best_only=True,mode='min',save_weights_only=True)
callbacks_list = [checkpoint]+my_callbacks

Model: "model_4"
__________________________________________________________________________________________________
 Layer (type)                Output Shape                 Param #   Connected to                  
 input_5 (InputLayer)        [(None, 30, 11)]             0         []                            
                                                                                                  
 conv1d_1 (Conv1D)           (None, 15, 16)               544       ['input_5[0][0]']             
                                                                                                  
 dropout_9 (Dropout)         (None, 15, 16)               0         ['conv1d_1[0][0]']            
                                                                                                  
 batch_normalization_16 (Ba  (None, 15, 16)               64        ['dropout_9[0][0]']           
 tchNormalization)                                                                          

In [53]:
history4=model4.fit(np.array(train1),np.array(rultrain),batch_size=64,epochs=EP(400),validation_data=(np.array(vali1),np.array(rulvali)),callbacks=callbacks_list)#,callbacks=[reduce_lr]

Epoch 1/3
563/565 [============================>.] - ETA: 0s - loss: 2409.3713 - rmse: 33.5783
Epoch 1: val_rmse improved from inf to 9.74071, saving model to ./data\weights4.best.hdf5
565/565 [==============================] - 7s 8ms/step - loss: 2402.1809 - rmse: 33.5013 - val_loss: 171.7223 - val_rmse: 9.7407
Epoch 2/3
555/565 [============================>.] - ETA: 0s - loss: 166.6560 - rmse: 9.8816
Epoch 2: val_rmse did not improve from 9.74071
565/565 [==============================] - 4s 7ms/step - loss: 166.2015 - rmse: 9.8673 - val_loss: 205.4332 - val_rmse: 11.1485
Epoch 3/3
564/565 [============================>.] - ETA: 0s - loss: 150.1159 - rmse: 9.3596
Epoch 3: val_rmse did not improve from 9.74071
565/565 [==============================] - 4s 7ms/step - loss: 150.0129 - rmse: 9.3560 - val_loss: 337.3859 - val_rmse: 14.7158


##Model 5：output physics rules


In [54]:
# class Myloss(Layer):
#  def __init__(self, input_shape,**kwargs):
#   self.is_placeholder = True
#   super(Myloss, self).__init__(**kwargs)
#  def myloss(self,sql,x, out):
#   x = K.flatten(x)
#   leng=len(x)
#   gap=int(sql/len(x))
#   kun=[]
#   sum=1-6*gap/out[0]
#   for i in range(1,leng):
#     sum=pow(sum,ma.log(out[i])/ma.log(out[i]))-6*gap/out[i]
#     kun.append(sum)
#   return K.mean(np.array(kun))
 
#  def call(self, inputs,OUT):
#   x = inputs
#   loss = self.myloss(x)
#   self.add_loss(loss, inputs=inputs)
#   return x
def myloss(y_true,y_pred):
  kun=[]
  h=0.0
  leng=len(y_pred)
  # gap=tf.cast(60/len(y_pred),tf.float32)
  sum1= tf.cast(1.0,tf.float32)
  for i in range(1,leng):
    k=abs(K.pow(sum1,K.log(y_pred[i])/K.log(y_pred[i-1])-6/K.log(y_pred[i])))
    sum1=K.sum(k)
    h+=sum1
  phyloss=K.mean(h)
  loss=K.mean(K.square(y_pred - y_true), axis=-1)
  total=loss+0.2*phyloss
  total=loss
  return total

In [55]:
inputs=Input(shape=(sql,11))
# r = Lambda(slice,output_shape=(16,1),arguments={'index':2})(inputs)
# r_loss_out=r
# r = MyLayer(sql,speed)(r)     
x = Conv1D(16,11,strides=2,padding='causal')(inputs)
x = Dropout(0.4)(x)
# x=MaxPooling1D(8)(x)
x=ResBlock(x,filters=16,kernel_size=2,dilation_rate=1,strides=1)
x=ResBlock(x,filters=8,kernel_size=2,dilation_rate=1,strides=1)
x=ResBlock(x,filters=4,kernel_size=2,dilation_rate=1,strides=1)# x=Conv1D(filters=16,kernel_size=2,padding='same',dilation_rate=4,activation='relu',kernel_initializer='orthogonal',
#                 bias_initializer='zeros')(x)   
x = GlobalAveragePooling1D()(x)
#x = Dense(8)(x)
#x = Dense(4)(x)
outputs = Dense(6,activation ='h_swish')(x)#,name='phy_out'
# output_01 = Dense(1, activation='relu')(outputs)
model5 = Model(inputs=inputs, outputs=outputs)
model5.compile(optimizer='adam',loss=myloss,metrics=[rmse],run_eagerly=True)
model5.summary()
filepath5=path+"weights5.best.hdf5"
my_callbacks = [
        # RocAucMetricCallback(),  # include it before EarlyStopping!
        EarlyStopping(monitor='val_rmse', patience=50, verbose=2, mode='min')
    ]
checkpoint = ModelCheckpoint(filepath5, monitor='val_rmse', verbose=1, save_best_only=True,mode='min',save_weights_only=True)
callbacks_list = [checkpoint]+my_callbacks

Model: "model_5"
__________________________________________________________________________________________________
 Layer (type)                Output Shape                 Param #   Connected to                  
 input_6 (InputLayer)        [(None, 30, 11)]             0         []                            
                                                                                                  
 conv1d_2 (Conv1D)           (None, 15, 16)               1952      ['input_6[0][0]']             
                                                                                                  
 dropout_12 (Dropout)        (None, 15, 16)               0         ['conv1d_2[0][0]']            
                                                                                                  
 batch_normalization_20 (Ba  (None, 15, 16)               64        ['dropout_12[0][0]']          
 tchNormalization)                                                                          

In [57]:
history5=model5.fit(np.array(train1),np.array(rultrain),batch_size=128,epochs=EP(500),validation_data=(np.array(vali1),np.array(rulvali)),callbacks=callbacks_list)

Epoch 1/3
283/283 [==============================] - ETA: 0s - loss: 4093.0061 - rmse: 51.7231
Epoch 1: val_rmse improved from inf to 34.70923, saving model to ./data\weights5.best.hdf5
283/283 [==============================] - 203s 717ms/step - loss: 4093.0061 - rmse: 51.7231 - val_loss: 1714.3453 - val_rmse: 34.7092
Epoch 2/3
283/283 [==============================] - ETA: 0s - loss: 243.2616 - rmse: 12.7280
Epoch 2: val_rmse did not improve from 34.70923
283/283 [==============================] - 187s 663ms/step - loss: 243.2616 - rmse: 12.7280 - val_loss: 2581.6829 - val_rmse: 42.5480
Epoch 3/3
283/283 [==============================] - ETA: 0s - loss: 169.0406 - rmse: 10.1390
Epoch 3: val_rmse did not improve from 34.70923
283/283 [==============================] - 178s 630ms/step - loss: 169.0406 - rmse: 10.1390 - val_loss: 1848.3496 - val_rmse: 36.4778
